In [2]:
import pandas as pd
import json
from pathlib import Path
import altair as alt

In [3]:
base_path = Path("data_cleaned")

In [47]:
responses = pd.concat([
    pd.read_json(base_path / "answers.jsonl", lines=True),
    pd.read_csv("response_annotations.csv", na_values=['NA', 'null']).drop(columns=['provider_key', 'question_id'])
], axis=1)
# responses = responses[~pd.isna(responses['address_as_patient'])]
responses


,question_id,provider_key,answer_markdown,answer_id,specialty,address_as_patient,verbatim_guidelines,specific_study_details,conflicting_evidence,dont_miss_items,gives_definitive_answer,begin_clinical_background,disclaimer
0,002a4c98-2f31-4de0-8820-fb48ae471712,claude-opus-4-8,"This is a nuanced clinical decision, and I'll ...",0,Oncology / Hematology,no,no,no,yes,NaN,no,no,yes
1,002a4c98-2f31-4de0-8820-fb48ae471712,gemini-3.1-pro,Based on standard oncologic guidelines and saf...,1,Oncology / Hematology,no,yes,yes,no,NaN,yes,no,yes
2,002a4c98-2f31-4de0-8820-fb48ae471712,gpt-5.5,**Short answer:** I would **not treat this as ...,2,Oncology / Hematology,no,yes,yes,yes,NaN,yes,no,no
3,002a4c98-2f31-4de0-8820-fb48ae471712,openevidence,**Proceeding with Cycle 4 is not appropriate a...,3,Oncology / Hematology,no,yes,yes,no,yes,yes,no,no
4,00368a91-5f7f-4361-84bc-15701d6053bb,claude-opus-4-8,Let me search for the specific N-staging break...,4,Oncology / Hematology,no,no,yes,no,NaN,no,no,no
...,...,...,...,...,...,...,...,...,...,...,...,...,...
2475,ff60257d-dd5a-46df-bcfd-fbc50386f2b7,openevidence,When **benzathine penicillin G (BPG) supplies ...,2475,Allergy & Immunology,no,yes,yes,yes,NaN,yes,no,no
2476,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,claude-opus-4-8,When evaluating whether thyroid dysfunction ma...,2476,Endocrinology,no,no,no,no,NaN,no,no,no
2477,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,gemini-3.1-pro,To determine whether thyroid dysfunction has d...,2477,Endocrinology,no,no,no,no,NaN,no,no,yes
2478,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,gpt-5.5,To judge whether **thyroid dysfunction may hav...,2478,Endocrinology,no,no,no,yes,NaN,no,no,no


In [75]:
# for col in responses.columns[-8:]:
#     print(col, (responses[col] == 'yes').groupby(responses['provider_key']).mean())
first_row = None
chart = None

response_attributes = responses.columns[-8:]

for i, col in enumerate(response_attributes):
    newc = alt.Chart(responses).mark_bar().encode(
        x="provider_key:N",
        color=col + ":O",
        y=alt.Y("count():Q", stack="normalize")
    ).properties(title=col, height=200)
    if i == 4: 
        first_row = chart
        chart = newc
    elif chart is None: chart = newc
    else: chart |= newc

first_row.resolve_scale(y='shared') & chart.resolve_scale(y='shared')

alt.VConcatChart(...)

In [49]:
pair_ratings = pd.read_csv(base_path / "ratings.csv")
pair_ratings_questions = pd.merge(pair_ratings,
                                  questions.rename(columns={'id': 'question_id'}),
                                  how='left',
                                  on='question_id')
pair_ratings_questions = pd.concat([
  pair_ratings_questions,
  pair_ratings_questions.assign(slot_a_provider=pair_ratings_questions["slot_b_provider"],
                                slot_b_provider=pair_ratings_questions["slot_a_provider"],
                                choice=pair_ratings_questions["choice"].replace({
                                  "strongly_a": "strongly_b",
                                  "slightly_a": "slightly_b",
                                  "strongly_b": "strongly_a",
                                  "slightly_b": "slightly_a",
                                })),
], axis=0)
pair_ratings_questions

,question_id,axis,choice,slot_a_provider,slot_b_provider,question_text,specialty
0,002a4c98-2f31-4de0-8820-fb48ae471712,accuracy,tie,openevidence,gemini-3.1-pro,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology
1,002a4c98-2f31-4de0-8820-fb48ae471712,accuracy,tie,openevidence,gpt-5.5,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology
2,002a4c98-2f31-4de0-8820-fb48ae471712,accuracy,tie,openevidence,gpt-5.5,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology
3,002a4c98-2f31-4de0-8820-fb48ae471712,authoritativeness,slightly_a,openevidence,gpt-5.5,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology
4,002a4c98-2f31-4de0-8820-fb48ae471712,authoritativeness,slightly_a,openevidence,gpt-5.5,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology
...,...,...,...,...,...,...,...
5775,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,accuracy,tie,claude-opus-4-8,openevidence,What additional history or symptoms would help...,Endocrinology
5776,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,authoritativeness,slightly_a,claude-opus-4-8,openevidence,What additional history or symptoms would help...,Endocrinology
5777,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,clinical_utility,slightly_a,claude-opus-4-8,openevidence,What additional history or symptoms would help...,Endocrinology
5778,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,completeness,strongly_a,claude-opus-4-8,openevidence,What additional history or symptoms would help...,Endocrinology


In [50]:
response_pair_attributes = pd.merge(pd.merge(pair_ratings_questions,
                                 responses[["question_id", "provider_key", "answer_markdown", *response_attributes]].rename(columns={"answer_markdown": "response_a", **{k: k + "_a" for k in response_attributes}}),
                                 how='left',
                                 left_on=['question_id', 'slot_a_provider'],
                                 right_on=['question_id', 'provider_key']).drop(columns=["provider_key"]),
                                 responses[["question_id", "provider_key", "answer_markdown", *response_attributes]].rename(columns={"answer_markdown": "response_b", **{k: k + "_b" for k in response_attributes}}),
                                 how='left',
                                 left_on=['question_id', 'slot_b_provider'],
                                 right_on=['question_id', 'provider_key']).drop(columns=["provider_key"])
response_pair_attributes

,question_id,axis,choice,slot_a_provider,slot_b_provider,question_text,specialty,response_a,address_as_patient_a,verbatim_guidelines_a,...,disclaimer_a,response_b,address_as_patient_b,verbatim_guidelines_b,specific_study_details_b,conflicting_evidence_b,dont_miss_items_b,gives_definitive_answer_b,begin_clinical_background_b,disclaimer_b
0,002a4c98-2f31-4de0-8820-fb48ae471712,accuracy,tie,openevidence,gemini-3.1-pro,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology,**Proceeding with Cycle 4 is not appropriate a...,no,yes,...,no,Based on standard oncologic guidelines and saf...,no,yes,yes,no,NaN,yes,no,yes
1,002a4c98-2f31-4de0-8820-fb48ae471712,accuracy,tie,openevidence,gpt-5.5,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology,**Proceeding with Cycle 4 is not appropriate a...,no,yes,...,no,**Short answer:** I would **not treat this as ...,no,yes,yes,yes,NaN,yes,no,no
2,002a4c98-2f31-4de0-8820-fb48ae471712,accuracy,tie,openevidence,gpt-5.5,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology,**Proceeding with Cycle 4 is not appropriate a...,no,yes,...,no,**Short answer:** I would **not treat this as ...,no,yes,yes,yes,NaN,yes,no,no
3,002a4c98-2f31-4de0-8820-fb48ae471712,authoritativeness,slightly_a,openevidence,gpt-5.5,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology,**Proceeding with Cycle 4 is not appropriate a...,no,yes,...,no,**Short answer:** I would **not treat this as ...,no,yes,yes,yes,NaN,yes,no,no
4,002a4c98-2f31-4de0-8820-fb48ae471712,authoritativeness,slightly_a,openevidence,gpt-5.5,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology,**Proceeding with Cycle 4 is not appropriate a...,no,yes,...,no,**Short answer:** I would **not treat this as ...,no,yes,yes,yes,NaN,yes,no,no
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
11555,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,accuracy,tie,claude-opus-4-8,openevidence,What additional history or symptoms would help...,Endocrinology,When evaluating whether thyroid dysfunction ma...,no,no,...,no,The key history elements that help determine w...,no,no,no,no,NaN,no,no,no
11556,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,authoritativeness,slightly_a,claude-opus-4-8,openevidence,What additional history or symptoms would help...,Endocrinology,When evaluating whether thyroid dysfunction ma...,no,no,...,no,The key history elements that help determine w...,no,no,no,no,NaN,no,no,no
11557,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,clinical_utility,slightly_a,claude-opus-4-8,openevidence,What additional history or symptoms would help...,Endocrinology,When evaluating whether thyroid dysfunction ma...,no,no,...,no,The key history elements that help determine w...,no,no,no,no,NaN,no,no,no
11558,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,completeness,strongly_a,claude-opus-4-8,openevidence,What additional history or symptoms would help...,Endocrinology,When evaluating whether thyroid dysfunction ma...,no,no,...,no,The key history elements that help determine w...,no,no,no,no,NaN,no,no,no


In [71]:
for attribute in response_attributes:
    matching_examples = response_pair_attributes[
        (response_pair_attributes[attribute + "_a"] == "yes") & 
        (response_pair_attributes[attribute + "_b"] != "yes")
    ]
    print(attribute, "=====", "Win Difference for Responses w/ Yes vs. No")
    for axis in response_pair_attributes["axis"].unique():
        axis_examples = matching_examples[matching_examples["axis"] == axis]
        weights = (len(matching_examples) / (matching_examples["slot_a_provider"].nunique() * matching_examples["slot_a_provider"].value_counts())).rename("weight")
        axis_examples = pd.merge(axis_examples, weights, left_on="slot_a_provider", right_index=True, how='left')
        wins = axis_examples["choice"].isin(["slightly_a", "strongly_a"]) * axis_examples["weight"]
        losses = axis_examples["choice"].isin(["slightly_b", "strongly_b"]) * axis_examples["weight"]
        print(axis.ljust(30), str(len(axis_examples)).ljust(5), f"{(wins.sum() - losses.sum()) / len(axis_examples):.1%}")
    print("")

address_as_patient ===== Win Difference for Responses w/ Yes vs. No
accuracy                       125   -21.6%
authoritativeness              125   -38.2%
clinical_utility               125   -19.3%
completeness                   125   -22.2%
verifiability                  125   -24.5%

verbatim_guidelines ===== Win Difference for Responses w/ Yes vs. No
accuracy                       388   18.1%
authoritativeness              388   27.0%
clinical_utility               388   22.8%
completeness                   388   30.6%
verifiability                  388   12.2%

specific_study_details ===== Win Difference for Responses w/ Yes vs. No
accuracy                       431   10.3%
authoritativeness              431   29.7%
clinical_utility               431   6.4%
completeness                   431   4.3%
verifiability                  431   9.8%

conflicting_evidence ===== Win Difference for Responses w/ Yes vs. No
accuracy                       296   5.0%
authoritativeness            

In [6]:
questions = pd.read_csv(base_path / "questions.csv")
questions_answers = pd.merge(
  questions,
  responses,
  how='left',
  on='question_id'
)
questions_answers

,question_id,question_text,specialty,provider_key,answer_markdown
0,002a4c98-2f31-4de0-8820-fb48ae471712,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology,claude-opus-4-8,"This is a nuanced clinical decision, and I'll ..."
1,002a4c98-2f31-4de0-8820-fb48ae471712,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology,gemini-3.1-pro,Based on standard oncologic guidelines and saf...
2,002a4c98-2f31-4de0-8820-fb48ae471712,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology,gpt-5.5,**Short answer:** I would **not treat this as ...
3,002a4c98-2f31-4de0-8820-fb48ae471712,Is it appropriate to proceed with Cycle 4 of F...,Oncology / Hematology,openevidence,**Proceeding with Cycle 4 is not appropriate a...
4,00368a91-5f7f-4361-84bc-15701d6053bb,What percentage of patients with N2 rectal can...,Oncology / Hematology,claude-opus-4-8,Let me search for the specific N-staging break...
...,...,...,...,...,...
2475,ff60257d-dd5a-46df-bcfd-fbc50386f2b7,What is the recommended management of syphilis...,Allergy & Immunology,openevidence,When **benzathine penicillin G (BPG) supplies ...
2476,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,What additional history or symptoms would help...,Endocrinology,claude-opus-4-8,When evaluating whether thyroid dysfunction ma...
2477,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,What additional history or symptoms would help...,Endocrinology,gemini-3.1-pro,To determine whether thyroid dysfunction has d...
2478,ffd0328e-8f67-4ea7-9c97-2ec6aeef20c6,What additional history or symptoms would help...,Endocrinology,gpt-5.5,To judge whether **thyroid dysfunction may hav...
